### Dataset and Task Metadata

In [1]:
from data_foundry.schema import DatasetMetadata, PredictiveMLTaskMetadata

dataset_mold = DatasetMetadata(
    unique_name="nci_ovarian_cancer",
    dataset_year="2002",
    domain_str="medical & healthcare",
    # Data Source
    dataset_source="GOV Website",
    original_dataset_source_download_link="https://home.ccr.cancer.gov/ncifdaproteomics/ppatterns.asp",
    download_description="""
We download the data to a predefined folder.

mkdir -p local-data-warehouse/nci_ovarian_cancer && wget -P local-data-warehouse/nci_ovarian_cancer https://home.ccr.cancer.gov/ncifdaproteomics/OvarianDataset8-7-02.zip && unzip local-data-warehouse/nci_ovarian_cancer/OvarianDataset8-7-02.zip -d local-data-warehouse/nci_ovarian_cancer/ && rm local-data-warehouse/nci_ovarian_cancer/OvarianDataset8-7-02.zip
""",
    # References
    academic_reference_bibtex="""@article{Petricoin2002UseOP,
  title={Use of proteomic patterns in serum to identify ovarian cancer},
  author={Emanuel F. Petricoin and Ali M. Ardekani and Ben A. Hitt and Peter J. Levine and Vincent A. Fusaro and Seth M. Steinberg and Gordon B. Mills and Charles Simone and David A. Fishman and Elise C. Kohn and Lance A. Liotta},
  journal={The Lancet},
  year={2002},
  volume={359},
  number={9306},
  pages={572-577},
  doi={10.1016/S0140-6736(02)07746-2},
  url={https://doi.org/10.1016/S0140-6736(02)07746-2}
}
""",
    academic_reference_bibtex_key="Petricoin2002UseOP",
    license="Public Domain",
    data_tags=["IID"],
    curation_comments="""
        - We merge all samples located in the .csv files into one DataFrame.
        - We label the samples based on name of the folder they are located in: "Control" translates to healthy patient cases while "Ovarian Cancer" to individuals with an ovarian cancer.
        - We drop duplicated 6 columns: Attribute 15148, Attribute 15149, Attribute 15150, Attribute 15151, Attribute 15152, Attribute 15153
        - We shuffle the data since it is concatenated in the folders order.
    """,
)
task_mold = PredictiveMLTaskMetadata(
    target_column_name="HasCancer",
    problem_type="binary_classification",
    objective_metric_name="roc_auc",
    stratify_on="HasCancer",
)

## Preprocessing

In [2]:
import os
import pandas as pd

valid_labels = {
    "Control",
    "Ovarian Cancer"
}

def csv_to_dataframe(file, label):
    """
    Convert each sample from the .csv file to a DataFrame with a label based on the name of the folder it is located in. 
    """
    label_map = {
        "Control": "No",
        "Ovarian Cancer": "Yes",
    }

    df = pd.read_csv(file).T
    df.reset_index(drop=True, inplace=True)
    df.drop(0, inplace=True)

    target_feature = "HasCancer"
    df.columns = [f"Attribute {i+1}" for i in range(len(df.columns) - 1)] + [target_feature]
    df[target_feature] = label_map.get(label, label)

    return df

r = {}
subdirs = [dirs[0] for dirs in os.walk(dataset_mold.path)][1:]
for subdir in subdirs:
    label = subdir.split("/")[-1]
    _, _, files = next(os.walk(subdir))
    r[label] = [os.path.join(subdir, name) for name in files]

df = pd.concat(
        [csv_to_dataframe(filepath, label) for label in r if label in valid_labels for filepath in r[label]], 
        ignore_index=True
    )
df["HasCancer"] = df["HasCancer"].astype("category")
df.drop(columns=["Attribute 15148", "Attribute 15149","Attribute 15150", "Attribute 15151","Attribute 15152","Attribute 15153"], inplace=True)
df = df.sample(frac=1, random_state=99).reset_index(drop=True)

## Data Checks

In [3]:
from data_foundry import dataset_checks
df_head, summary, numeric_stats, cat_stats, target_df = dataset_checks.run_all_checks(
    data=df,
    classification=task_mold.is_classification,
    target_feature=task_mold.target_column_name,
    print_report=False, # In notebook...
)


#### Dataset Overview
Rows: 253
Columns: 15148
Use sampling: False (sample size: 253)
Get row duplicates (staged, merged)...
Using top-10 columns for initial filtering: ['Attribute 9671', 'Attribute 9790', 'Attribute 1235', 'Attribute 8275', 'Attribute 9511', 'Attribute 9428', 'Attribute 10293', 'Attribute 10294', 'Attribute 9789', 'Attribute 1239']
Rows remaining as candidates after top-10 filter: 0 (of 253)

#### Duplicate Report
Total duplicate rows: 0 (0.00% of dataset)
Duplicate rows ignoring target: 0 (0.00% of dataset)
Get column duplicates...
Duplicate columns: 0 (0.00% of columns)

Data quality checks completed.


In [4]:
# Sample Rows
df_head

,Attribute 1,Attribute 2,Attribute 3,Attribute 4,Attribute 5,Attribute 6,Attribute 7,Attribute 8,Attribute 9,Attribute 10,Attribute 11,Attribute 12,Attribute 13,Attribute 14,Attribute 15,Attribute 16,Attribute 17,Attribute 18,Attribute 19,Attribute 20,Attribute 21,Attribute 22,Attribute 23,Attribute 24,Attribute 25,Attribute 26,Attribute 27,Attribute 28,Attribute 29,Attribute 30,Attribute 31,Attribute 32,Attribute 33,Attribute 34,Attribute 35,Attribute 36,Attribute 37,Attribute 38,Attribute 39,Attribute 40,Attribute 41,Attribute 42,Attribute 43,Attribute 44,Attribute 45,Attribute 46,Attribute 47,Attribute 48,Attribute 49,Attribute 50,Attribute 51,Attribute 52,Attribute 53,Attribute 54,Attribute 55,Attribute 56,Attribute 57,Attribute 58,Attribute 59,Attribute 60,Attribute 61,Attribute 62,Attribute 63,Attribute 64,Attribute 65,Attribute 66,Attribute 67,Attribute 68,Attribute 69,Attribute 70,Attribute 71,Attribute 72,Attribute 73,Attribute 74,Attribute 75,Attribute 76,Attribute 77,Attribute 78,Attribute 79,Attribute 80,Attribute 81,Attribute 82,Attribute 83,Attribute 84,Attribute 85,Attribute 86,Attribute 87,Attribute 88,Attribute 89,Attribute 90,Attribute 91,Attribute 92,Attribute 93,Attribute 94,Attribute 95,Attribute 96,Attribute 97,Attribute 98,Attribute 99,Attribute 100,Attribute 101,Attribute 102,Attribute 103,Attribute 104,Attribute 105,Attribute 106,Attribute 107,Attribute 108,Attribute 109,Attribute 110,Attribute 111,Attribute 112,Attribute 113,Attribute 114,Attribute 115,Attribute 116,Attribute 117,Attribute 118,Attribute 119,Attribute 120,Attribute 121,Attribute 122,Attribute 123,Attribute 124,Attribute 125,Attribute 126,Attribute 127,Attribute 128,Attribute 129,Attribute 130,Attribute 131,Attribute 132,Attribute 133,Attribute 134,Attribute 135,Attribute 136,Attribute 137,Attribute 138,Attribute 139,Attribute 140,Attribute 141,Attribute 142,Attribute 143,Attribute 144,Attribute 145,Attribute 146,Attribute 147,Attribute 148,Attribute 149,Attribute 150,Attribute 151,Attribute 152,Attribute 153,Attribute 154,Attribute 155,Attribute 156,Attribute 157,Attribute 158,Attribute 159,Attribute 160,Attribute 161,Attribute 162,Attribute 163,Attribute 164,Attribute 165,Attribute 166,Attribute 167,Attribute 168,Attribute 169,Attribute 170,Attribute 171,Attribute 172,Attribute 173,Attribute 174,Attribute 175,Attribute 176,Attribute 177,Attribute 178,Attribute 179,Attribute 180,Attribute 181,Attribute 182,Attribute 183,Attribute 184,Attribute 185,Attribute 186,Attribute 187,Attribute 188,Attribute 189,Attribute 190,Attribute 191,Attribute 192,Attribute 193,Attribute 194,Attribute 195,Attribute 196,Attribute 197,Attribute 198,Attribute 199,Attribute 200,Attribute 201,Attribute 202,Attribute 203,Attribute 204,Attribute 205,Attribute 206,Attribute 207,Attribute 208,Attribute 209,Attribute 210,Attribute 211,Attribute 212,Attribute 213,Attribute 214,Attribute 215,Attribute 216,Attribute 217,Attribute 218,Attribute 219,Attribute 220,Attribute 221,Attribute 222,Attribute 223,Attribute 224,Attribute 225,Attribute 226,Attribute 227,Attribute 228,Attribute 229,Attribute 230,Attribute 231,Attribute 232,Attribute 233,Attribute 234,Attribute 235,Attribute 236,Attribute 237,Attribute 238,Attribute 239,Attribute 240,Attribute 241,Attribute 242,Attribute 243,Attribute 244,Attribute 245,Attribute 246,Attribute 247,Attribute 248,Attribute 249,Attribute 250,Attribute 251,Attribute 252,Attribute 253,Attribute 254,Attribute 255,Attribute 256,Attribute 257,Attribute 258,Attribute 259,Attribute 260,Attribute 261,Attribute 262,Attribute 263,Attribute 264,Attribute 265,Attribute 266,Attribute 267,Attribute 268,Attribute 269,Attribute 270,Attribute 271,Attribute 272,Attribute 273,Attribute 274,Attribute 275,Attribute 276,Attribute 277,Attribute 278,Attribute 279,Attribute 280,Attribute 281,Attribute 282,Attribute 283,Attribute 284,Attribute 285,Attribute 286,Attribute 287,Attribute 288,Attribute 289,Attribute 290,Attribute 291,Attribute 292,Attribute 293,Attri

In [5]:
# Feature Summary
summary

,index,dtype,n_missing,pct_missing,n_unique,examples
0,HasCancer,category,0.0,0.0,2.0,"Yes, No"
1,Attribute 1,float64,0.0,0.0,73.0,"4.1126, 4.1689, 4.1549, 4.1428, 4.1528, 4.173, 4.1629, 4.1146, 4.1488, 4.1569"
2,Attribute 2,float64,0.0,0.0,76.0,"4.1207, 4.1609, 4.1106, 4.1448, 4.1408, 4.1146, 4.1227, 4.1066, 4.1368, 4.1488"
3,Attribute 3,float64,0.0,0.0,67.0,"4.0825, 4.0965, 4.0543, 4.0845, 4.0985, 4.1207, 4.0463, 4.0724, 4.0664, 4.0644"
4,Attribute 4,float64,0.0,0.0,73.0,"4.1549, 4.1287, 4.1347, 4.1589, 4.1569, 4.1609, 4.1448, 4.175, 4.1508, 4.1166"
5,Attribute 5,float64,0.0,0.0,69.0,"4.0322, 4.0704, 4.0845, 4.0362, 4.0483, 4.0503, 4.0402, 4.0603, 4.0684, 4.0282"
6,Attribute 6,float64,0.0,0.0,62.0,"3.9457, 3.9759, 3.9537, 3.9558, 3.9336, 3.9477, 3.9899, 3.9437, 3.9175, 3.9578"
7,Attribute 7,float64,0.0,0.0,61.0,"3.9075, 3.9035, 3.9477, 3.8954, 3.9175, 3.9377, 3.9276, 3.9397, 3.9135, 3.8974"
8,Attribute 8,float64,0.0,0.0,67.0,"4.0101, 3.9819, 4.0241, 4.0362, 3.9859, 4.006, 4.0, 3.996, 3.9739, 3.9638"
9,Attribute 9,float64,0.0,0.0,62.0,"4.0322, 4.0644, 4.0603, 4.0241, 4.008, 4.0101, 4.0161, 4.0664, 4.0261, 4.0503"


In [6]:
# Numeric Feature Statistics
numeric_stats

,count,mean,std,min,max
Attribute 1,253.0,4.155893,0.034252,4.056310,4.243338
Attribute 2,253.0,4.132929,0.036022,4.048266,4.231272
Attribute 3,253.0,4.083519,0.034366,4.002011,4.176973
Attribute 4,253.0,4.153318,0.036837,4.080442,4.253394
Attribute 5,253.0,4.053122,0.033179,3.971845,4.140774
Attribute 6,253.0,3.959127,0.029438,3.881347,4.040221
Attribute 7,253.0,3.917880,0.029317,3.839115,4.008044
Attribute 8,253.0,4.007957,0.032743,3.929613,4.082453
Attribute 9,253.0,4.031454,0.029950,3.957768,4.096531
Attribute 10,253.0,4.035682,0.034542,3.953746,4.136752


In [7]:
# Categorical Feature Statistics
cat_stats

value  count    pct
column    rank                    
HasCancer 1      Yes    162  64.03
          2       No     91  35.97

In [8]:
# Target Distribution
target_df

,count,pct
HasCancer,,
Yes,162,64.03
No,91,35.97


## Task Curation

In [9]:
from data_foundry.curation_recommendations import get_recommended_splits_dimensions

n_repeats, n_splits, none_or_test_size = get_recommended_splits_dimensions(
    dataset=df,
    group_on=task_mold.group_on,
    time_on=task_mold.time_on,
)
print(f"Recommended splits: n_repeats={n_repeats}, n_splits={n_splits}, test_size={none_or_test_size}")

Recommended splits: n_repeats=20, n_splits=3, test_size=None


In [10]:
from data_foundry.schema import PredictiveMLSplitsMetadata
from data_foundry import curation_recommendations

splits = curation_recommendations.get_recommended_iid_splits(
    dataset=df,
    n_repeats=n_repeats,
    n_splits=n_splits,
    test_size=none_or_test_size,
    stratify_on=task_mold.stratify_on,
)

splits_mold = PredictiveMLSplitsMetadata(
    splits_comment="Default splits.",
    splits=splits,
)

Using Stratified IID splits.


## Export

In [11]:
from data_foundry.curation_container import CuratedContainer
curated_data = CuratedContainer(
    dataset=df,
    dataset_metadata=dataset_mold,
    task_metadata=task_mold,
    experiment_metadata=splits_mold,
 )
curated_data.save()
print(curated_data.uuid)
print(curated_data.checksum)

Calculating checksum for curated container...
Saving curated container to nci_ovarian_cancer/019d9d1f-b718-7871-ae91-44ed77e79e46
019d9d1f-b718-7871-ae91-44ed77e79e46
a35884ef91e5c386422040bd24f307645a02101aef4e7008bbcd1d8c188d5d47
